# Exploration of Watershed Boundary (HUC-8) Dataset

In [1]:
import geopandas as gpd
import pandas as pd

## Initial Investigation

In [2]:
gpkg_path = "../data/raw/wbd/WBD_National_GPKG.gpkg"
wbd_df = gpd.read_file(gpkg_path,layer="WBDHU8")
wbd_df.head()

,tnmid,metasourceid,sourcedatadesc,sourceoriginator,sourcefeatureid,loaddate,referencegnis_ids,areaacres,areasqkm,states,huc8,name,globalid,shape_Length,shape_Area,geometry
0,{DA87EC7E-FB57-4A0E-8713-10567559A58B},{511D2AC8-11BA-45FC-AB98-F69D693D4C44},Watershed Boundary Dataset (WBD),Natural Resources and Conservation Service and...,None,2024-08-16 10:24:20+00:00,626170,851585.17,3446.25,MI,04080204,Flint,{510E22D6-AB4D-4CDD-99CF-5CD58FEC5B94},4.645777,0.380858,"MULTIPOLYGON (((-83.24547 43.35439, -83.24507 ..."
1,{34237FD4-D8C2-47F4-8989-29AC92CA256D},{511D2AC8-11BA-45FC-AB98-F69D693D4C44},Watershed Boundary Dataset (WBD),Natural Resources and Conservation Service and...,None,2024-08-16 10:24:20+00:00,1867316,510065.30,2064.16,MI,04090003,Clinton,{A207672D-3D88-4E02-A497-D0CF75350200},3.381461,0.226767,"MULTIPOLYGON (((-83.01797 42.94371, -83.01772 ..."
2,{9518B2C0-766D-44A0-A156-DCA8E4551527},{511D2AC8-11BA-45FC-AB98-F69D693D4C44},Watershed Boundary Dataset (WBD),Natural Resources and Conservation Service and...,None,2024-08-16 10:24:20+00:00,1562290,673271.29,2724.63,"MI,WI",04030106,Brule,{AC5B9190-DEC8-4111-AF08-6C5993737A75},5.047323,0.317390,"MULTIPOLYGON (((-88.54782 46.53939, -88.54764 ..."
3,{2983B57A-C017-4813-9063-51B4213FF9AB},{511D2AC8-11BA-45FC-AB98-F69D693D4C44},Watershed Boundary Dataset (WBD),Natural Resources and Conservation Service and...,None,2024-08-16 10:24:20+00:00,248771,3206053.92,12974.45,"CA,MX",18100204,Salton Sea,{52127BF8-0115-49EC-BD9A-C06290D20546},8.257299,1.251929,"MULTIPOLYGON (((-115.92055 33.81369, -115.9204..."
4,{EF9CDE22-5978-45F7-95A8-36E84D408C08},{511D2AC8-11BA-45FC-AB98-F69D693D4C44},Watershed Boundary Dataset (WBD),Natural Resources and Conservation Service and...,None,2024-08-16 10:24:20+00:00,1621113,888549.87,3595.84,"MI,WI",04020102,Ontonagon,{29BE3289-DDD4-4B1D-98FB-33A3D2DBD493},5.163753,0.421148,"MULTIPOLYGON (((-89.32617 46.87654, -89.32562 ..."


In [3]:
wbd_df.info()

<class 'geopandas.geodataframe.GeoDataFrame'>
RangeIndex: 2456 entries, 0 to 2455
Data columns (total 16 columns):
 #   Column             Non-Null Count  Dtype              
---  ------             --------------  -----              
 0   tnmid              2456 non-null   str                
 1   metasourceid       2429 non-null   str                
 2   sourcedatadesc     2395 non-null   str                
 3   sourceoriginator   2426 non-null   str                
 4   sourcefeatureid    0 non-null      object             
 5   loaddate           2455 non-null   datetime64[ms, UTC]
 6   referencegnis_ids  2349 non-null   str                
 7   areaacres          2449 non-null   float64            
 8   areasqkm           2445 non-null   float64            
 9   states             2456 non-null   str                
 10  huc8               2456 non-null   str                
 11  name               2456 non-null   str                
 12  globalid           2456 non-null   str  

In [4]:
wbd_df.describe()

,areaacres,areasqkm,shape_Length,shape_Area
count,2.449000e+03,2445.000000,2456.000000,2456.000000
mean,1.135573e+06,4599.513450,5.386664,0.553176
std,1.164492e+06,4715.222603,3.514385,0.688240
min,2.440708e+04,98.770000,0.334411,0.008869
25%,5.721887e+05,2315.590000,3.507093,0.243869
50%,8.653398e+05,3504.010000,4.595288,0.370417
75%,1.319159e+06,5346.780000,6.072477,0.581599
max,2.099013e+07,84944.110000,50.484566,10.561233


In [5]:
# Check for duplicate names
duplicates = wbd_df[wbd_df["name"].duplicated(keep=False)].sort_values("name")
print(f"The HUC8 dataset contains {len(duplicates)} watersheds with the same name")
duplicates[["name", "huc8", "states"]].head(30)

The HUC8 dataset contains 241 watersheds with the same name


,name,huc8,states
185,Bayou Pierre,11140206,"LA,TX"
1223,Bayou Pierre,08060203,"LA,MS"
1738,Bear,11040005,"CO,KS"
758,Bear,06030006,"AL,MS"
425,Beaver,10130104,ND
1393,Beaver,10050014,MT
1433,Beaver,10110204,"MT,ND"
1273,Beaver,10190013,CO
582,Beaver,10250014,"KS,NE"
130,Beaver,10120107,"SD,WY"


Given that there are multiple watersheds with the same name, joining the dam removals based on name can get messy. Instead, a spatial join will be performed below; dams will be joined to the watersheds based on whether or not their coordinates are within a watershed polygon.

## Join to dam removal dataset

In [6]:
dam_df = pd.read_csv('../data/raw/dams/ARDamRemovalList_Figshare_Mar2026.csv')
merged = dam_df.merge(
    wbd_df,
    left_on="HUC8",
    right_on="name",
    how="left"
)

print(f"The joined table has {merged.shape[0]} rows and {merged.shape[1]} columns")
print(f"There are {len(merged['HUC8'].dropna().unique())} unique HUC8s")


The joined table has 2596 rows and 38 columns
There are 678 unique HUC8s


In [7]:
print(dam_df.shape)

(2325, 22)


In [8]:
# Convert dams to GeoDataFrame
dam_gdf = gpd.GeoDataFrame(
    dam_df,
    geometry=gpd.points_from_xy(
        dam_df["Longitude"],
        dam_df["Latitude"]
    ),
    crs="EPSG:4326"
)

# Make sure WBD uses the same CRS (coordinate system)
wbd_huc8 = wbd_df.to_crs(dam_gdf.crs)

# Spatial join
merged_df = gpd.sjoin(
    dam_gdf,
    wbd_huc8[["huc8", "name", "geometry"]],
    how="left",
    predicate="within"
)

print(merged_df.shape)

merged_df.head(20)

(2325, 26)


,AR_ID,NABI_ID,NID_ID,Dam_Name,Year_Removed,Latitude,Longitude,City_County,River,HUC8,...,Type_Material,Reason_for_removal,Miles_Restored_US,Miles_Restored_DS,River_Miles_Reported,Last_Updated,geometry,index_right,huc8,name
0,AK-001,AK91779,NaN,Lake Bettinger Complex Dam,NaN,57.803330,-152.395000,Kodiak,NaN,Kodiak-Afognak Islands,...,Timber,Delapidated,NaN,NaN,NaN,2/10/2026,POINT (-152.395 57.80333),1323.0,19020701,Kodiak-Afognak Islands
1,AK-002,AK91780,NaN,Bettinger Lower Reservoir Dam B,NaN,57.801670,-152.395000,Kodiak,NaN,Kodiak-Afognak Islands,...,Timber,Safety,NaN,NaN,NaN,2/10/2026,POINT (-152.395 57.80167),1323.0,19020701,Kodiak-Afognak Islands
2,AK-003,AK91781,NaN,Memory Estates Dam #1,NaN,62.618330,-149.427000,Matanuska-Susitna,NaN,Talkeetna River,...,Earthen,NaN,NaN,NaN,NaN,2/10/2026,POINT (-149.427 62.61833),2228.0,19020503,Talkeetna River
3,AK-004,AK91782,NaN,Memory Estates Dam #2,NaN,62.626670,-149.380000,Matanuska-Susitna,NaN,Talkeetna River,...,Earthen,NaN,NaN,NaN,NaN,2/10/2026,POINT (-149.38 62.62667),2228.0,19020503,Talkeetna River
4,AK-005,NaN,NaN,Switzer One Dam,1988,NaN,NaN,"Tongass National Forest, Juneau",Switzer Creek,Lynn Canal,...,NaN,Safety,NaN,NaN,NaN,11/10/2017,POINT (NaN NaN),NaN,NaN,NaN
5,AK-006,AK91783,NaN,Switzer Two Dam,1988,58.365000,-134.500000,"Tongass National Forest, Juneau",Switzer Creek,Lynn Canal,...,NaN,Safety,NaN,NaN,NaN,2/10/2026,POINT (-134.5 58.365),213.0,19010301,Lynn Canal
6,AK-007,AK45539,NaN,City of Kake Dam,2000,56.981540,-133.931000,Kake,Gunnuk Creek,Kuiu-Kupreanof-Mitkof Islands,...,NaN,Safety,NaN,NaN,NaN,2/10/2026,POINT (-133.931 56.98154),2287.0,19010210,Kuiu-Kupreanof-Mitkof Islands
7,AK-008,AK91784,NaN,Davidson Ditch Diversion Dam,2002,65.292800,-146.404000,Fairbanks North Star,Chatanika River,Tolovana River,...,NaN,Safety/Ecology,NaN,NaN,65,2/10/2026,POINT (-146.404 65.2928),2208.0,19080309,Tolovana River
8,AK-009,NaN,NaN,Unnamed (Bridle Path Dam),2004,NaN,NaN,NaN,Allison Creek,NaN,...,Concrete,Ecology,NaN,NaN,NaN,2/4/2022,POINT (NaN NaN),NaN,NaN,NaN
9,AK-010,AK91785,AK00093,Lower Eklutna River Dam,2017,61.449393,-149.323880,Anchorage,Eklutna,Anchorage,...,Concrete,Ecology,NaN,NaN,16,2/10/2026,POINT (-149.32388 61.44939),1157.0,19020401,Anchorage


In [9]:
print(f"There are {len(merged_df['AR_ID'].dropna().unique())} unique dams") # should be 2325

There are 2325 unique dams


## Extract HUC4 codes from HUC8 codes in joined dataset to get all relevant HUC4 watersheds

This is done so that only a subset of all streams in the US are downloaded - we do not want to download the entire stream dataset as this would be ginormous

In [10]:
huc8s = merged_df['huc8'].dropna().unique()
print(f"HUC 8s: {list(huc8s)}")

print("\n\n\n")

huc4s = merged_df['huc8'].str[:4].dropna().unique()
print(f"HUC 4s: {list(huc4s)}")

HUC 8s: ['19020701', '19020503', '19010301', '19010210', '19080309', '19020401', '03150202', '03130003', '03150106', '03160111', '03150108', '03160202', '08020203', '11010003', '11140109', '11010005', '11010001', '15060203', '15010001', '15060101', '15050301', '18010211', '18010101', '18010103', '18050005', '18010108', '18010102', '18020158', '18020154', '18050004', '18010110', '18040012', '18040008', '18050002', '18060008', '18060015', '18010207', '18040013', '18010107', '18010210', '18020153', '18020162', '18020005', '18050006', '18070101', '18040010', '18050003', '18020152', '18070301', '18070102', '18060006', '18060013', '18070104', '18010106', '18020121', '18070203', '18040009', '18020126', '18010206', '18020002', '18060002', '10190006', '10190005', '10190003', '10190007', '14020004', '11020005', '11020002', '10190004', '14010004', '11020003', '11020006', '14020002', '10190001', '11020001', '01100005', '01100002', '01100004', '01100001', '01080205', '01100006', '01100003', '010802

In [11]:
print(f"The dam removals are in {len(huc4s)} HUC4 watersheds. There are 245 HUC4 watersheds in the US (https://nas.er.usgs.gov/hucs.aspx)")

The dam removals are in 156 HUC4 watersheds. There are 245 HUC4 watersheds in the US (https://nas.er.usgs.gov/hucs.aspx)


## Write hucs to text file to aid stream downloads

In [12]:
with open("../data/processed/huc4_list.txt", "w") as f:
    f.write("\n".join(huc4s))
print("Success!")

Success!


In [13]:
# Confirm file contents are correct
from pathlib import Path

huc4_file = Path("../data/processed/huc4_list.txt")
huc4s = [
    x.strip()
    for x in huc4_file.read_text().splitlines()
    if x.strip()
]

print(len(huc4s))

156


Examination of the NHDPlus API reveals that only some HUC-4s are downloadable. Further, only some HUC-8s are downloadable. Thus, we must create a second text file for HUC-8s. Download logic will be handled with the python script.

In [14]:
with open("../data/processed/huc8_list.txt", "w") as f:
    f.write("\n".join(huc8s))
print("Success!")

Success!


## Now, visualize HUC 8 Watersheds and Dam Removals on a map

In [17]:
%pip install folium

Note: you may need to restart the kernel to use updated packages.


In [19]:
import folium
from folium import GeoJson, FeatureGroup
from folium.plugins import MarkerCluster

# Folium requires WGS84 coordinates
print("Beginning folium setup...")

relevant_hucs = merged_df["huc8"].dropna().unique()

watersheds = wbd_huc8[
    wbd_huc8["huc8"].isin(relevant_hucs)
].to_crs("EPSG:4326")

# Simplify watershed boundaries for visualization only
watersheds_map = watersheds.copy()

watersheds_map["geometry"] = (
    watersheds_map.geometry.simplify(
        tolerance=0.001,
        preserve_topology=True
    )
)

print("Watersheds simplified for mapping")

dams = merged_df.to_crs("EPSG:4326")

# Center map on the dam dataset
center = [
    dams.geometry.y.mean(),
    dams.geometry.x.mean()
]

m = folium.Map(
    location=center,
    zoom_start=5,
    tiles="OpenStreetMap"
)

# HUC8 watershed polygons
print("Beginning watersheds...")
huc_layer = FeatureGroup(
    name="HUC8 Watersheds",
    show=True
)

GeoJson(
    watersheds_map[["huc8", "name", "geometry"]],
    style_function=lambda feature: {
        "fillColor": "#4C9F70",
        "color": "#28734A",
        "weight": 1,
        "fillOpacity": 0.12
    },
    tooltip=folium.GeoJsonTooltip(
        fields=["huc8", "name"],
        aliases=["HUC8:", "Watershed:"]
    )
).add_to(huc_layer)

print("Watershed layer constructed")

huc_layer.add_to(m)

# Dam removal markers
print("Beginning dams...")

dam_layer = FeatureGroup(
    name="Dam Removals",
    show=True
)

# Keep only valid point geometries
valid_dams = dams[
    dams.geometry.notna()
    & ~dams.geometry.is_empty
    & dams.geometry.is_valid
].copy()

valid_dams = valid_dams[
    valid_dams.geometry.x.between(-180, 180)
    & valid_dams.geometry.y.between(-90, 90)
]

# Add dam locations as one GeoJSON layer
GeoJson(
    valid_dams[["huc8", "name", "geometry"]],
    name="Dam Removals",
    marker=folium.CircleMarker(
        radius=4,
        color="red",
        fill=True,
        fill_opacity=0.7
    ),
    tooltip=folium.GeoJsonTooltip(
        fields=["huc8", "name"],
        aliases=["HUC8:", "Watershed:"]
    )
).add_to(dam_layer)

dam_layer.add_to(m)

print("Dam layer constructed")

folium.LayerControl(collapsed=False).add_to(m)

m

Beginning folium setup...
Watersheds simplified for mapping
Beginning watersheds...
Watershed layer constructed
Beginning dams...
Dam layer constructed
